# Web Scraper - Vitrine Sebrae Startups


## 📊 Extração Completa dos Dados

**Desenvolvido por:** NUTEC  
**Data:** Março 2026  
**Objetivo:** Extrair os dados estruturados de todas as startups da Vitrine Sebrae

**Total de páginas:** ~1089  
**Startups estimadas:** ~13.056


---

# 📦 1. Instalação de Dependências

In [ ]:
# @title CELULA 1: Instala todas as bibliotecas necessárias para o scraping
!pip install -q requests pandas tqdm gspread google-auth pytz

import requests
import pandas as pd
import time
import re
import pytz
from datetime import datetime
from typing import List, Dict, Optional, Tuple
from tqdm.notebook import tqdm
import logging
from pathlib import Path
import concurrent.futures
import warnings
warnings.filterwarnings('ignore')

# Fuso-horário de Fortaleza (UTC-3, sem horário de verão)
FUSO_FORTALEZA = pytz.timezone('America/Fortaleza')

def agora() -> datetime:
    """Retorna datetime atual com timezone de Fortaleza."""
    return datetime.now(FUSO_FORTALEZA)

# Logging — só erros no Colab para não poluir a saída
logging.basicConfig(level=logging.ERROR, format='%(asctime)s - [%(levelname)s] - %(message)s')
logger = logging.getLogger(__name__)

# 🔑 2. Autenticação Do Google Drive


In [ ]:
# ============================================================
# @title CELULA 2: Solicita a autorização de acesso do Google Drive
# ============================================================
# ID da pasta de destino no Google Drive (compartilhada com editor).
# Mude ela para que os arquivos csv sejam criados dentro de outra pasta do google drive
CLIENTE_FOLDER_ID = '1H1pdZKaFn5Xln6NlpOUMMaaXkMLMqGvK'






try:
    from google.colab import drive
    from google.colab import auth
    from google.auth import default
    import gspread

    # 1. Monta o Drive localmente
    drive.mount('/content/drive')

    # 2. Autentica o usuário (abrirá um popup pedindo permissão)
    print('🔑 Autenticando no Google Drive e Sheets...')
    auth.authenticate_user()
    creds, _ = default()
    gc = gspread.authorize(creds)
    print('✅ Autenticado no Google Sheets com sucesso!')

    # 3. Resolve o caminho real da pasta pelo ID — funciona independente de quem rodou
    #    ou de onde a pasta está no Drive (inclusive em drives compartilhados).
    try:
        from googleapiclient.discovery import build
        _drive_svc = build('drive', 'v3', credentials=creds)
        _meta = _drive_svc.files().get(
            fileId=CLIENTE_FOLDER_ID,
            fields='id,name',
            supportsAllDrives=True
        ).execute()
        # Usa uma pasta local temporária para staging dos arquivos antes do upload via API.
        # Isso evita depender do caminho montado do Drive (que muda por usuário).
        _TEMP_BASE = Path('/content/drive_output') / CLIENTE_FOLDER_ID
        _TEMP_BASE.mkdir(parents=True, exist_ok=True)
        OUTPUT_DIR = _TEMP_BASE
        print(f"✅ Pasta destino resolvida: '{_meta['name']}' (ID: {CLIENTE_FOLDER_ID})")
        print(f'   Arquivos serão salvos localmente em {OUTPUT_DIR} e enviados via API para o Drive.')
    except Exception as _e:
        # Fallback: tenta o caminho padrão montado no Drive
        print(f'⚠️ Não foi possível resolver pasta por ID ({_e}). Usando caminho padrão no Drive.')
        OUTPUT_DIR = Path('/content/drive/MyDrive/C-JOVEM & Nutec 2026')
        OUTPUT_DIR.mkdir(parents=True, exist_ok=True)
        print(f'✅ Google Drive conectado! Salvando em: {OUTPUT_DIR}')

except ImportError:
    OUTPUT_DIR = Path('./C-JOVEM_&_Nutec_2026')   # local fallback
    OUTPUT_DIR.mkdir(parents=True, exist_ok=True)
    gc = None
    print(f'⚠️ Ambiente local (não-Colab). Salvando em: {OUTPUT_DIR}')
    print(f'⚠️ Google Sheets Sync desabilitado localmente.')

Drive already mounted at /content/drive; to attempt to forcibly remount, call drive.mount("/content/drive", force_remount=True).
🔑 Autenticando no Google Drive e Sheets...


✅ Autenticado no Google Sheets com sucesso!
✅ Pasta destino resolvida: 'C-JOVEM & Nutec 2026' (ID: 1H1pdZKaFn5Xln6NlpOUMMaaXkMLMqGvK)
   Arquivos serão salvos localmente em /content/drive_output/1H1pdZKaFn5Xln6NlpOUMMaaXkMLMqGvK e enviados via API para o Drive.


# 🛠️ 3. Funções Auxiliares e de Execução



In [ ]:
# ============================================================
# @title CELULA 3: Funções auxiliares que são usadas pela classe principal
# ============================================================
def processar_dfs(scraper) -> Tuple[pd.DataFrame, pd.DataFrame, pd.DataFrame]:
    """Cria os 3 DataFrames bases e trata os campos faltantes."""
    df = pd.DataFrame(scraper.dados_coletados)
    if df.empty:
        return df, df, df

    for col in ['email', 'phone', 'description', 'siteUrl', 'imageUrl']:
        if col in df.columns:
            df[col] = df[col].fillna('')

    df_validos = df[(df['name'].str.len() > 1) & (df['has_contact'] == True) & (df['is_complete'] == True)]
    df_incomp  = df[df['is_complete'] == False]
    return df, df_validos, df_incomp

def salvar_csvs(scraper, df, df_validos, df_incomp) -> dict:
    if df.empty:
        print('\n❌ Nenhum dado para salvar em CSV.')
        return {}

    # CSVs Principais
    df.to_csv(scraper.output_dir / 'COMPLETO.csv', index=False, encoding='utf-8-sig')
    df_validos.to_csv(scraper.output_dir / 'DADOS_VALIDOS.csv', index=False, encoding='utf-8-sig')
    df_incomp.to_csv(scraper.output_dir / 'DADOS_INVALIDOS.csv', index=False, encoding='utf-8-sig')

    # CSV de Erros
    if scraper.erros_coleta:
        df_erros = pd.DataFrame(scraper.erros_coleta)
        df_erros.to_csv(scraper.output_dir / 'ERROS.csv', index=False, encoding='utf-8-sig')

    return {
        'total': len(df),
        'validos': len(df_validos),
        'incomp': len(df_incomp),
        'sem_email': int((df['email'] == '').sum()),
        'sem_fone': int((df['phone'] == '').sum()),
        'sem_desc': int((df['description'] == '').sum()),
        'sem_site': int((df['siteUrl'] == '').sum()),
        'sem_img': int((df['imageUrl'] == '').sum()),
    }

def sync_com_google_sheets(df_completo, df_validos, df_incomp, folder_id=None, share_email=None):
    global gc
    if not gc:
        print("\n⚠️ Ignorando Sync com Sheets (Não autenticado).")
        return

    sheet_name = 'Dashboard_Startups_Sebrae'
    print(f"\n☁️ Iniciando sincronização com Google Sheets ('{sheet_name}')...")
    try:
        try:
            sh = gc.open(sheet_name)
        except gspread.exceptions.SpreadsheetNotFound:
            if folder_id:
                print(f"   Criando nova planilha '{sheet_name}' direto na pasta destino...")
                sh = gc.create(sheet_name, folder_id=folder_id)
            else:
                print(f"   Criando nova planilha '{sheet_name}' na raiz do seu Drive...")
                sh = gc.create(sheet_name)

            if share_email:
                print(f"   Compartilhando planilha com '{share_email}'...")
                sh.share(share_email, perm_type='user', role='writer')

        def update_aba(aba_nome, df):
            try:
                worksheet = sh.worksheet(aba_nome)
            except gspread.exceptions.WorksheetNotFound:
                worksheet = sh.add_worksheet(title=aba_nome, rows=max(100, len(df)+10), cols=30)

            worksheet.clear()
            if not df.empty:
                data = [df.columns.values.tolist()] + df.astype(str).values.tolist()
                worksheet.update(data)
            print(f"   ✓ Aba '{aba_nome}' limpa e atualizada com {len(df)} registros.")

        update_aba('COMPLETO', df_completo)
        update_aba('VALIDOS', df_validos)
        update_aba('INVALIDOS', df_incomp)

        for default_name in ['Página1', 'Sheet1', 'Página 1']:
            try:
                aba_padrao = sh.worksheet(default_name)
                if aba_padrao and len(sh.worksheets()) > 1:
                    sh.del_worksheet(aba_padrao)
            except Exception:
                pass

        print(f"✅ Sincronização concluída com sucesso!")
        print(f"🔗 Link da Planilha: {sh.url}")
    except Exception as e:
        print(f"❌ Erro crítico ao comunicar com o Google Sheets: {e}")

def enviar_csvs_drive_api(output_dir: Path, folder_id: str):
    """Envia CSVs e o relatório TXT para a pasta destino no Drive via API."""
    global creds
    if 'creds' not in globals(): return
    try:
        from googleapiclient.discovery import build
        from googleapiclient.http import MediaFileUpload

        print("\n☁️ Enviando CSVs e Relatório para a pasta destino via API...")
        service = build('drive', 'v3', credentials=creds)

        # Lista arquivos já existentes para evitar duplicatas (reescreve a versão anterior)
        results = service.files().list(
            q=f"'{folder_id}' in parents and trashed=false",
            pageSize=100, fields="files(id, name)",
            supportsAllDrives=True, includeItemsFromAllDrives=True
        ).execute()
        arquivos_na_nuvem = {f['name']: f['id'] for f in results.get('files', [])}

        # Faz upload de CSVs e do relatório TXT
        MIME_MAP = {'.csv': 'text/csv', '.txt': 'text/plain'}
        for file_path in output_dir.glob('*'):
            if file_path.is_file() and file_path.suffix in MIME_MAP:
                mime = MIME_MAP[file_path.suffix]
                media = MediaFileUpload(str(file_path), mimetype=mime, resumable=True)

                if file_path.name in arquivos_na_nuvem:
                    print(f"   Atualizando '{file_path.name}'...")
                    service.files().update(
                        fileId=arquivos_na_nuvem[file_path.name], media_body=media
                    ).execute()
                else:
                    print(f"   Criando '{file_path.name}'...")
                    service.files().create(
                        body={'name': file_path.name, 'parents': [folder_id]},
                        media_body=media, supportsAllDrives=True
                    ).execute()

        print("✅ Arquivos transferidos com sucesso para a pasta do cliente!")
    except Exception as e:
        print(f"❌ Erro ao enviar arquivos para o Drive via API: {e}")

def gerar_relatorio_txt(scraper, d_stats, total, validos, incompletos):
    """
    Gera/atualiza um único arquivo 'relatorio.txt' na pasta de saída.
    Layout visual com emojis e barras decorativas, amigável para leitores não técnicos.
    Cada nova execução é inserida no topo, mantendo o histórico abaixo.
    Fuso horário: Fortaleza (UTC-3).
    """
    if total == 0:
        return

    now           = agora()
    data_str      = now.strftime('%d/%m/%Y')
    hora_str      = now.strftime('%H:%M')
    duration      = str(scraper.stats['end_time'] - scraper.stats['start_time']).split('.')[0]
    report_file   = scraper.output_dir / 'relatorio.txt'

    total_count_real = scraper.stats.get('total_count_real', '?')
    pages_failed     = scraper.stats['failed']
    pages_requested  = scraper.stats['total_requests'] - 1
    fail_rate        = (pages_failed / pages_requested * 100) if pages_requested > 0 else 0
    erros_graves     = scraper.stats['server_errors']

    # ── Status geral ──────────────────────────────────────────────────────────
    if fail_rate > 50:
        status_icone = "⛔"
        status_linha = "PROBLEMA  —  A maioria das páginas falhou. Dados podem estar incompletos."
    elif erros_graves > 10 or fail_rate > 10:
        status_icone = "⚠️ "
        status_linha = "PARCIAL   —  Houve algumas falhas, mas a maior parte dos dados foi coletada."
    else:
        status_icone = "✅"
        status_linha = "SUCESSO   —  Coleta concluída sem nenhum problema!"

    pct_val = (validos     / total * 100) if total else 0
    pct_inc = (incompletos / total * 100) if total else 0

    def barra(val, total_val, length=30):
        """Barra de progresso visual com blocos Unicode."""
        if total_val == 0:
            return "░" * length + "  0%"
        filled = int(length * val / total_val)
        return "█" * filled + "░" * (length - filled) + f"  {val/total_val*100:.0f}%"

    def campo_status(val):
        if val == 0:
            return "✓  Todos preenchidos"
        pct = val / total * 100 if total else 0
        return f"✗  {val} sem dado  ({pct:.0f}% do total)"

    # ── Bordas decorativas ────────────────────────────────────────────────────
    BORDA_TOPO    = "╔" + "═" * 68 + "╗"
    BORDA_MEIO    = "╠" + "═" * 68 + "╣"
    BORDA_FIM     = "╚" + "═" * 68 + "╝"
    SECAO         = "┄" * 70
    DIVISOR_HIST  = "·" * 70   # divisor entre relatórios históricos

    def caixa(texto):
        """Linha com borda esquerda apenas — evita desalinhamento por emojis de largura dupla."""
        return f"║  {texto}"

    L = []   # lista de linhas do relatório

    # ── CABEÇALHO ─────────────────────────────────────────────────────────────
    L.append(BORDA_TOPO)
    L.append(caixa(""))
    L.append(caixa("🚀  VITRINE SEBRAE — RELATÓRIO DE COLETA DE DADOS"))
    L.append(caixa(f"📅  {data_str}   🕐  {hora_str}   (horário de Fortaleza)"))
    L.append(caixa(""))
    L.append(BORDA_MEIO)
    L.append(caixa(f"  {status_icone}  {status_linha}"))
    L.append(caixa(f"  ⏱️   Duração da coleta: {duration}"))
    L.append(caixa(""))
    L.append(BORDA_FIM)
    L.append("")

    # ── RESULTADO GERAL ───────────────────────────────────────────────────────
    L.append(f"  📊  O QUE FOI COLETADO?")
    L.append(SECAO)
    L.append("")
    L.append(f"  O script percorreu o site da Vitrine Sebrae e encontrou:")
    L.append(f"    🌐  Total oficial no site  :  {total_count_real} startups")
    L.append(f"    📥  Total baixado agora     :  {total} startups")
    L.append("")
    L.append(f"  Dessas {total} startups coletadas:")
    L.append("")
    L.append(f"    ✅  Completas   ({pct_val:.0f}%)  {barra(validos, total)}")
    L.append(f"        → {validos} startups com e-mail, telefone, site e descrição")
    L.append("")
    L.append(f"    ⚠️   Incompletas ({pct_inc:.0f}%)  {barra(incompletos, total)}")
    L.append(f"        → {incompletos} startups com algum dado faltando")
    L.append("")

    # ── CAMPOS FALTANTES ──────────────────────────────────────────────────────
    L.append(f"  📋  QUAIS DADOS ESTÃO FALTANDO?")
    L.append(SECAO)
    L.append("")
    L.append(f"    📧  E-mail      :  {campo_status(d_stats['sem_email'])}")
    L.append(f"    📞  Telefone    :  {campo_status(d_stats['sem_fone'])}")
    L.append(f"    📝  Descrição   :  {campo_status(d_stats['sem_desc'])}")
    L.append(f"    🌐  Site        :  {campo_status(d_stats['sem_site'])}")
    L.append(f"    🖼️   Imagem/Logo :  {campo_status(d_stats['sem_img'])}")
    L.append("")

    # ── ARQUIVOS GERADOS ──────────────────────────────────────────────────────
    L.append(f"  📁  ARQUIVOS ATUALIZADOS NA PASTA:")
    L.append(SECAO)
    L.append("")
    L.append(f"    📄  COMPLETO.csv        —  todas as {total} startups coletadas")
    L.append(f"    ✅  DADOS_VALIDOS.csv   —  {validos} startups com dados completos")
    L.append(f"    ❌  DADOS_INVALIDOS.csv —  {incompletos} startups com algum dado faltando")
    L.append(f"    📒  relatorio.txt       —  este arquivo de resumo")
    if scraper.erros_coleta:
        L.append(f"    ⚠️   ERROS.csv           —  {len(scraper.erros_coleta)} páginas que falharam")
    L.append("")

    # ── DADOS TÉCNICOS ────────────────────────────────────────────────────────
    L.append(f"  🔧  INFORMAÇÕES TÉCNICAS  (para o time de TI)")
    L.append(SECAO)
    L.append("")
    L.append(f"    • Páginas processadas  :  {pages_requested}")
    L.append(f"    • Falhas de rede       :  {pages_failed}  ({fail_rate:.1f}%)")
    L.append(f"    • Erros no servidor    :  {erros_graves}")
    L.append(f"    • Retentativas         :  {scraper.stats['retries']}")
    L.append("")

    if scraper.erros_coleta:
        L.append(f"    📋  Páginas que falharam (primeiras 20):")
        L.append(f"    {'Horário':<12}  {'Tipo de Erro':<28}  Página / URL")
        L.append("    " + "─" * 62)
        for erro in scraper.erros_coleta[:20]:
            ts  = str(erro.get('timestamp', '?'))[11:19]
            er  = str(erro.get('erro', '?'))[:26]
            url = str(erro.get('url', str(erro.get('page', 'N/A'))))
            L.append(f"    {ts:<12}  {er:<28}  {url}")
        L.append("")

    # ── RODAPÉ ────────────────────────────────────────────────────────────────
    L.append(BORDA_FIM)
    L.append("")

    # 5 linhas em branco + divisor visual entre relatórios históricos
    L.append("")
    L.append("")
    L.append("")
    L.append("")
    L.append(DIVISOR_HIST)
    L.append(f"   ↑  Relatório de {data_str} às {hora_str}  —  fim deste registro")
    L.append(DIVISOR_HIST)
    L.append("")
    L.append("")
    L.append("")
    L.append("")
    L.append("")

    novo_conteudo = "\n".join(L)

    # Lê conteúdo anterior e coloca o novo no topo
    conteudo_anterior = ""
    if report_file.exists():
        try:
            with open(report_file, 'r', encoding='utf-8') as f:
                conteudo_anterior = f.read()
        except Exception:
            pass

    with open(report_file, 'w', encoding='utf-8') as f:
        f.write(novo_conteudo + conteudo_anterior)

    print(f'📄 Relatório atualizado com sucesso: {report_file.name}')


# 🤖 4. Classe Principal do Scraper

### ✅ Campos extraídos:
- **type**: Tipo (Startup ou Projeto Inovador) ✅
- **name**: Nome da empresa ✅
- **city**: Cidade ✅
- **state**: Estado (UF) ✅
- **local**: Localização (cidade/estado) ✅
- **siteUrl**: Website oficial ✅
- **email**: Email de contato ✅
- **phone**: Telefone de contato ✅
- **maturity_pt**: Estágio de Maturidade ✅
- **segment_pt**: Categoria/Segmento ✅
- **description_pt**: Descrição completa ✅
- **imageUrl**: URL do logo ✅


In [ ]:
# ============================================================
# @title CELULA 4: Classe que Recebe todas as informações das Startups
# ============================================================
class SebraeScraper:
    BASE_URL = 'https://vitrine.sebraestartups.com.br/?page='
    MAX_PAGES_SAFE_LIMIT = 3000
    MAX_WORKERS = 3
    DELAY_BETWEEN_REQUESTS = 1.0
    DELAY_BETWEEN_BATCHES = 2.0
    MAX_RETRIES = 5
    TIMEOUT = 30

    def __init__(self, output_dir: Path):
        self.output_dir = Path(output_dir)
        self.dados_coletados: List[Dict] = []
        self.erros_coleta: List[Dict] = []
        self.stats = {
            'total_requests': 0, 'success': 0, 'failed': 0,
            'retries': 0, 'server_errors': 0, 'ignored_no_name': 0,
            'start_time': None, 'end_time': None,
        }
        self.session = requests.Session()
        self.session.headers.update({
            'User-Agent': 'Mozilla/5.0 (Windows NT 10.0)',
            'Accept': 'text/html,application/xhtml+xml,application/xml;q=0.9,*/*;q=0.8',
        })

    def request_page(self, url: str) -> Tuple[Optional[str], int]:
        self.stats['total_requests'] += 1
        for tentativa in range(self.MAX_RETRIES):
            try:
                response = self.session.get(url, timeout=self.TIMEOUT)
                if response.status_code == 404:
                    return None, tentativa + 1
                if response.status_code >= 500:
                    self.stats['server_errors'] += 1
                response.raise_for_status()
                self.stats['success'] += 1
                return response.text, tentativa + 1
            except requests.RequestException as e:
                self.stats['retries'] += 1
                wait = (tentativa + 1) * 2
                time.sleep(wait)
        self.stats['failed'] += 1
        self.erros_coleta.append({'url': url, 'erro': 'Max Retries Exceeded', 'timestamp': agora().isoformat()})
        return None, self.MAX_RETRIES

    def parse_html(self, html: str, page_num: int) -> Tuple[List[Dict], int]:
        if not html: return [], 0
        startups = []
        ignored = 0
        for part in html.split('imageUrl')[1:]:
            def get_val(key):
                patterns = [
                    f'\\\\\"{key}\\\\\":\\\\\"((?:[^\\\\\"]|\\\\.)*?)\\\\\"',
                    f'\"{key}\":\"((?:[^\"]|\\\\.)*?)\"',
                    f'\\\\\"{key}\\\\\":\\\\\"\\\\\\\\\\\\\"((?:[^\\\\\"]|\\\\.)*?)\\\\\\\\\\\\\"',
                ]
                candidates = []
                for p in patterns:
                    for m in re.findall(p, part):
                        candidates.append(m.replace('\\"', '"').replace('\\n', '\n'))
                if candidates:
                    return max(candidates, key=len).strip('\\"').strip('"')
                return ''

            name = get_val('name')
            if not name:
                ignored += 1
                continue

            img_match = re.match(r'\\?\":\\?\"([^\"]+)\"', part)
            email, phone = get_val('email'), get_val('phone')
            raw_desc = get_val('description_pt')
            siteUrl = get_val('siteUrl')

            missing = []
            if not email: missing.append('Email')
            if not phone: missing.append('Telefone')
            if len(raw_desc) <= 3: missing.append('Descrição')
            if not siteUrl: missing.append('Site')
            if not (img_match and img_match.group(1)): missing.append('Imagem')

            startups.append({
                'name': name, 'city': get_val('city'), 'state': get_val('state'),
                'email': email, 'phone': phone,
                'has_contact': bool(email or phone),
                'is_complete': not bool(missing),
                'missing_fields': ', '.join(missing) if missing else 'Completo',
                'maturity': get_val('maturity_pt'),
                'segment': get_val('segment_pt'),
                'siteUrl': siteUrl,
                'description': raw_desc if len(raw_desc) > 3 else '',
                'imageUrl': img_match.group(1) if img_match else '',
                'page_source': page_num,
                'scraped_at': agora().isoformat(),
            })
        return startups, ignored

    def process_page(self, page_num: int) -> Tuple[List[Dict], int]:
        url = f'{self.BASE_URL}{page_num}'
        time.sleep(self.DELAY_BETWEEN_REQUESTS)
        html, _ = self.request_page(url)
        if not html: return [], 0
        return self.parse_html(html, page_num)

    def fetch_metadata(self) -> dict:
        html, _ = self.request_page(f'{self.BASE_URL}1')
        total_pages = None
        total_count = None
        if html:
            tp_match = re.search(r'"totalPages"\s*:\s*(\d+)', html)
            if tp_match: total_pages = int(tp_match.group(1))

            # Busca count baseada no padrão exato do dashboard localizando a array de segments
            count_match = re.search(r'"count"\s*:\s*(\d+)\s*,\s*"segments"', html)
            if count_match: total_count = int(count_match.group(1))

        return {'total_pages': total_pages, 'total_count': total_count}

    def run(self, start_page: int = 1, end_page: Optional[int] = None):
        self.stats['start_time'] = agora()
        meta = self.fetch_metadata()
        total_pages = meta.get('total_pages')
        total_count = meta.get('total_count')
        target_total = end_page if end_page else total_pages

        self.stats['total_pages_real'] = total_pages
        self.stats['total_count_real'] = total_count

        tc_display = total_count if total_count else 'Todas as'
        if end_page: desc = f'Páginas {start_page}–{end_page}' + (f' de {total_pages}' if total_pages else '') + f' | {tc_display} startups no site'
        else: desc = f'Todas as páginas' + (f' (total: {total_pages})' if total_pages else '') + f' | {tc_display} startups no site'
        print(f'\n🚀 SCRAPER | Threads: {self.MAX_WORKERS} | {desc}\n')

        all_startups = []
        empty_streak = 0
        STOP_THRESHOLD = 5

        with concurrent.futures.ThreadPoolExecutor(max_workers=self.MAX_WORKERS) as executor:
            batch_size = 10
            current_page = start_page
            pbar = tqdm(initial=start_page, total=target_total, desc='Páginas Analisadas', unit='pag')

            while True:
                if end_page and current_page > end_page: break
                if current_page > self.MAX_PAGES_SAFE_LIMIT: break

                limit = end_page if end_page else (current_page + batch_size)
                if end_page and limit > end_page: limit = end_page

                pages_in_batch = list(range(current_page, min(current_page + batch_size, limit + 1) if end_page else current_page + batch_size))
                if not pages_in_batch: break

                future_to_page = {executor.submit(self.process_page, p): p for p in pages_in_batch}
                batch_empty = True

                for future in concurrent.futures.as_completed(future_to_page):
                    pg = future_to_page[future]
                    try:
                        data, ignored_n = future.result()
                        self.stats['ignored_no_name'] += ignored_n
                        pbar.update(1)
                        if data:
                            all_startups.extend(data)
                            batch_empty = False
                            empty_streak = 0
                        else:
                            empty_streak += 1
                    except Exception as exc:
                        self.erros_coleta.append({'page': pg, 'erro': str(exc), 'timestamp': agora().isoformat()})
                        pbar.update(1)

                pbar.set_postfix({'startups coletadas': f"{len(all_startups)}/{total_count if total_count else '~13058'}"})
                if not end_page:
                    if batch_empty or empty_streak >= STOP_THRESHOLD:
                        print(f'\n🛑 Fim detectado (Página {current_page}). Encerrando.')
                        break

                current_page += batch_size
                if not (end_page and current_page > end_page): time.sleep(self.DELAY_BETWEEN_BATCHES)
            pbar.close()

        self.dados_coletados = all_startups
        self.stats['end_time'] = agora()
        print(f"\n✅ Coleta Finalizada! {len(all_startups)} resultados carregados em memória.")

# 🚀 5. Configurações de Execução

**Escolha quantas páginas processar:**
- `3` páginas = ~36 startups (Teste rápido)
- `1089` páginas = ~13.000 startups (Teste completo)

In [ ]:
# ============================================================
# @title CELULA 5: Função de Execução do Scraping
# ============================================================

scraper = SebraeScraper(output_dir=OUTPUT_DIR)

# 1. Fala até que pagina deve ir, ajuste se necessario:
#   scraper.run(start_page=1, end_page=10) -> para testes rápidos
#   scraper.run(start_page=1, end_page=None) -> para percorrer todas as páginas

# 👇 ALTERE AQUI O NÚMERO DE PÁGINAS
scraper.run(start_page=1, end_page=None)


🚀 SCRAPER | Threads: 3 | Todas as páginas | Todas as startups no site



Páginas Analisadas: 1pag [00:00, ?pag/s]


🛑 Fim detectado (Página 1091). Encerrando.

✅ Coleta Finalizada! 13057 resultados carregados em memória.


# 💾 6. Salvar e Preencher Planilhar



In [ ]:
# ============================================================
# @title CELULA 6: Salva os Dados no CSV e na Planilha
# ============================================================

# 1. Dispara a trilha de salvamento (CSV -> Sheets -> TXT)
if scraper.dados_coletados:
    print(f"\n{'='*60}\n💾 INICIANDO GRAVAÇÃO — {agora().strftime('%d/%m/%Y %H:%M')} (Fortaleza)\n{'='*60}")

    # Prepara os dataframes
    df_comp, df_val, df_inc = processar_dfs(scraper)

    # Salva CSVs localmente e recupera as estatísticas
    d_stats = salvar_csvs(scraper, df_comp, df_val, df_inc)

    # Imprime resumo no terminal
    tot, val, inc = d_stats['total'], d_stats['validos'], d_stats['incomp']
    ign = scraper.stats.get('ignored_no_name', 0)
    print(f'📂 Total coletado : {tot} startups')
    if ign > 0:
        print(f'Ignoradas : {ign} startups desconsideradas (sem nome)')
    print(f'✅ Válidas         : {val:>6} ({(val/tot*100) if tot else 0:.1f}%)')
    print(f'⚠️  Incompletas    : {inc:>6} ({(inc/tot*100) if tot else 0:.1f}%)')
    print(f"{'─'*60}")

    # Sincroniza abas no Google Sheets (usa o ID definido na Célula 2)
    sync_com_google_sheets(df_comp, df_val, df_inc, folder_id=CLIENTE_FOLDER_ID)

    # Gera/atualiza o Relatório TXT (arquivo único, mais recente no topo)
    gerar_relatorio_txt(scraper, d_stats, tot, val, inc)

    # Envia todos os CSVs e o TXT do relatório para a pasta destino via API
    enviar_csvs_drive_api(OUTPUT_DIR, CLIENTE_FOLDER_ID)
    print(f"{'='*60}")



💾 INICIANDO GRAVAÇÃO — 24/03/2026 20:01 (Fortaleza)
📂 Total coletado : 13057 startups
Ignoradas : 1 startups desconsideradas (sem nome)
✅ Válidas         :  10921 (83.6%)
⚠️  Incompletas    :   2136 (16.4%)
────────────────────────────────────────────────────────────

☁️ Iniciando sincronização com Google Sheets ('Dashboard_Startups_Sebrae')...
   ✓ Aba 'COMPLETO' limpa e atualizada com 13057 registros.
   ✓ Aba 'VALIDOS' limpa e atualizada com 10921 registros.
   ✓ Aba 'INVALIDOS' limpa e atualizada com 2136 registros.
✅ Sincronização concluída com sucesso!
🔗 Link da Planilha: https://docs.google.com/spreadsheets/d/1Ftld3bHzDKJvjf40KcOwSl3gikD0YOx_ZmAyl9hvHjA
📄 Relatório atualizado com sucesso: relatorio.txt

☁️ Enviando CSVs e Relatório para a pasta destino via API...
   Atualizando 'DADOS_INVALIDOS.csv'...
   Atualizando 'relatorio.txt'...
   Atualizando 'COMPLETO.csv'...
   Atualizando 'DADOS_VALIDOS.csv'...
✅ Arquivos transferidos com sucesso para a pasta do cliente!


## 📊  7. Prévia dos Dados

In [ ]:
# ============================================================
# @title CELULA 7: Visualiza todos os dados extraídos das startups
# ============================================================
# Nota: Só execute essa célula se a CÉLULA 5 já finalizou a execução com sucesso.
try:
    if df_comp.empty:
        print("❌ Nenhum dado em memória.")
    else:

        # ── 1. COMPLETO ──────────────────────────────────────────
        print(f"\n{'='*60}\n📂 COMPLETO — {len(df_comp)} registros\n{'='*60}\n")
        with pd.option_context('display.max_rows', None, 'display.max_colwidth', 120):
            display(df_comp)

        # ── 2. DADOS_VALIDOS ─────────────────────────────────────
        print(f"\n{'='*60}\n✅ DADOS_VALIDOS — {len(df_val)} registros\n{'='*60}\n")
        with pd.option_context('display.max_rows', None, 'display.max_colwidth', 120):
            display(df_val)

        # ── 3. DADOS_INVALIDOS ───────────────────────────────────
        print(f"\n{'='*60}\n⚠️  DADOS_INVALIDOS — {len(df_inc)} registros\n{'='*60}\n")
        with pd.option_context('display.max_rows', None, 'display.max_colwidth', 120):
            display(df_inc)
except NameError:
    print("❌ Execute a CÉLULA 5 primeiro.")



📂 COMPLETO — 13057 registros



,name,city,state,email,phone,has_contact,is_complete,missing_fields,maturity,segment,siteUrl,description,imageUrl,page_source,scraped_at
0,ARCO - Ações para compostagem e Reciclagem,Porto Alegre,RS,,(51) 99191-7447,True,False,Email,Escala,Impacto socioambiental,www.arcoresiduos.com.br,"ARCO realiza gestão 360º de resíduos para estabelecimentos de P e M porte (bares, restaurantes, hotéis), O serviço, ...",https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1686329078523x117536423921054780/ARCO_Branding_ArquivosDaMar...,2,2026-03-24T19:40:13.364439-03:00
1,ATERRA,Belo Horizonte,MG,fernando.andrade@aterraambiental.com.br,(31) 98485-9927,True,True,Completo,Escala,Impacto socioambiental,www.aterraambiental.com,Além da possibilidade de reversão do impacto negativo ao meio ambiente e a sociedade por conta da destinação incorre...,https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1684866085299x215385500288012300/marcaAterra-03.png\,2,2026-03-24T19:40:13.364804-03:00
2,AWISE QuantoSobra,Santa Cruz do Sul,RS,stefano.willig@quantosobra.com.br,(51) 98015-8611,True,True,Completo,Escala,Varejo e Atacado,https://www.useawise.com,"AWISE: O ERP que transforma sua loja. Reduzindo erros, retrabalho e poupando tempo, nosso software impulsiona sua lu...",https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1687528294649x615137644340309000/awise-doquantosobra-central...,2,2026-03-24T19:40:13.365038-03:00
3,Abufarí coleta e beneficiamento de produtos florestais LTDA Abufarí Proodutos Amazônicos,Tapauá,AM,financeiro@abufari.com,(41) 99685-1899,True,True,Completo,Escala,Alimentos e Bebidas,abufai.com.br,A Abufarí Produtos Amazônicos nasceu a partir do entendimento da existência de uma riqueza tipicamente brasileira e ...,https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1698757845960x673767564834084900/logoabufari.jpg\,2,2026-03-24T19:40:13.365337-03:00
4,Acertpix,São Paulo,SP,andre.azevedo@acertpix.com.br,(31) 98834-1566,True,True,Completo,Escala,Crédito e Finanças,acertpix.com.br,"Somos uma IDtech, utilizando AI para previnir fraudes para o mercado financeiro. Crescemos 22x de 2021 para 2022, no...",https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1688215380199x314074585700618430/logo.JPG\,2,2026-03-24T19:40:13.365524-03:00
5,Acom Sistemas Corporativos,Curitiba,PR,drechmer@acomsistemas.com.br,(41) 99927-7861,True,True,Completo,Escala,Alimentos e Bebidas,https://acomsistemas.com.br,A ACOM Sistemas é uma FoodTech que desenvolve soluções integradas de gestão para o backoffice do food service. Nossa...,https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1695244526645x981115378552349700/default-image_550.png?_gl=1...,2,2026-03-24T19:40:13.365760-03:00
6,Adapt Edtech,Florianópolis,SC,evandro.salles@adaptedtech.com.br,(11) 94054-4668,True,True,Completo,Escala,Educação,https://www.adaptedtech.com.br/,"Construímos soluções educacionais e corporativas personalizadas, potencializamos resultados e rompemos barreiras com...",https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1744660509302x251101523289476450/logo_full-TTR8Pats.webp\,2,2026-03-24T19:40:13.366027-03:00
7,Adotar,Campo Grande,MS,gabriel.potumati@gmail.com,(67) 99961-8997,True,True,Completo,Escala,Impacto socioambiental,https://adotar.com.br,"Somos o maior portal do Brasil para adoção e doação de animais, já auxiliamos mais de 200mil animais, atualmente uti...",https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1686247793440x584039176145012600/logo.png\,2,2026-03-24T19:40:13.368413-03:00
8,Adweb,Montes Claros,MG,romulogomes@embratec.org,(38) 99104-2613,True,True,Completo,Escala,Comunicação e Mídia,Adwebapp.com,Aplicativo de inteligência artificial para criação e gestão de anúncios on-line.,https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1689637369699x739518904992617600/Logotipo%20Adweb%20Azul%20M...,2,2026-03-24T19:40:13.368592-03:00
9,Aeroscan/Drones Inteligentes,Barueri,SP,marcoforjaz@aeroscan.com.br,(11) 96470-6179,True,True,Completo,Escala,Tecnologia


✅ DADOS_VALIDOS — 10921 registros



,name,city,state,email,phone,has_contact,is_complete,missing_fields,maturity,segment,siteUrl,description,imageUrl,page_source,scraped_at
1,ATERRA,Belo Horizonte,MG,fernando.andrade@aterraambiental.com.br,(31) 98485-9927,True,True,Completo,Escala,Impacto socioambiental,www.aterraambiental.com,Além da possibilidade de reversão do impacto negativo ao meio ambiente e a sociedade por conta da destinação incorre...,https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1684866085299x215385500288012300/marcaAterra-03.png\,2,2026-03-24T19:40:13.364804-03:00
2,AWISE QuantoSobra,Santa Cruz do Sul,RS,stefano.willig@quantosobra.com.br,(51) 98015-8611,True,True,Completo,Escala,Varejo e Atacado,https://www.useawise.com,"AWISE: O ERP que transforma sua loja. Reduzindo erros, retrabalho e poupando tempo, nosso software impulsiona sua lu...",https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1687528294649x615137644340309000/awise-doquantosobra-central...,2,2026-03-24T19:40:13.365038-03:00
3,Abufarí coleta e beneficiamento de produtos florestais LTDA Abufarí Proodutos Amazônicos,Tapauá,AM,financeiro@abufari.com,(41) 99685-1899,True,True,Completo,Escala,Alimentos e Bebidas,abufai.com.br,A Abufarí Produtos Amazônicos nasceu a partir do entendimento da existência de uma riqueza tipicamente brasileira e ...,https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1698757845960x673767564834084900/logoabufari.jpg\,2,2026-03-24T19:40:13.365337-03:00
4,Acertpix,São Paulo,SP,andre.azevedo@acertpix.com.br,(31) 98834-1566,True,True,Completo,Escala,Crédito e Finanças,acertpix.com.br,"Somos uma IDtech, utilizando AI para previnir fraudes para o mercado financeiro. Crescemos 22x de 2021 para 2022, no...",https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1688215380199x314074585700618430/logo.JPG\,2,2026-03-24T19:40:13.365524-03:00
5,Acom Sistemas Corporativos,Curitiba,PR,drechmer@acomsistemas.com.br,(41) 99927-7861,True,True,Completo,Escala,Alimentos e Bebidas,https://acomsistemas.com.br,A ACOM Sistemas é uma FoodTech que desenvolve soluções integradas de gestão para o backoffice do food service. Nossa...,https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1695244526645x981115378552349700/default-image_550.png?_gl=1...,2,2026-03-24T19:40:13.365760-03:00
6,Adapt Edtech,Florianópolis,SC,evandro.salles@adaptedtech.com.br,(11) 94054-4668,True,True,Completo,Escala,Educação,https://www.adaptedtech.com.br/,"Construímos soluções educacionais e corporativas personalizadas, potencializamos resultados e rompemos barreiras com...",https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1744660509302x251101523289476450/logo_full-TTR8Pats.webp\,2,2026-03-24T19:40:13.366027-03:00
7,Adotar,Campo Grande,MS,gabriel.potumati@gmail.com,(67) 99961-8997,True,True,Completo,Escala,Impacto socioambiental,https://adotar.com.br,"Somos o maior portal do Brasil para adoção e doação de animais, já auxiliamos mais de 200mil animais, atualmente uti...",https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1686247793440x584039176145012600/logo.png\,2,2026-03-24T19:40:13.368413-03:00
8,Adweb,Montes Claros,MG,romulogomes@embratec.org,(38) 99104-2613,True,True,Completo,Escala,Comunicação e Mídia,Adwebapp.com,Aplicativo de inteligência artificial para criação e gestão de anúncios on-line.,https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1689637369699x739518904992617600/Logotipo%20Adweb%20Azul%20M...,2,2026-03-24T19:40:13.368592-03:00
9,Aeroscan/Drones Inteligentes,Barueri,SP,marcoforjaz@aeroscan.com.br,(11) 96470-6179,True,True,Completo,Escala,Tecnologia da Informação,www.aeroscan.com.br,"Somos uma startup que entrega múltiplas soluções utilizando drones, desenvolvemos um software que permite automatiza...",https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1714259515545x361152397995614850/logo_aeroscan_vertical_posi...,2,2026-03-24T19:40:13.368866-03:00
10,AfroCentrados Conceito,Salvador,BA,afrocentradoscolab@gmail.com,(71) 99208-8769,True,True,Completo,Escala,Moda 


⚠️  DADOS_INVALIDOS — 2136 registros



,name,city,state,email,phone,has_contact,is_complete,missing_fields,maturity,segment,siteUrl,description,imageUrl,page_source,scraped_at
0,ARCO - Ações para compostagem e Reciclagem,Porto Alegre,RS,,(51) 99191-7447,True,False,Email,Escala,Impacto socioambiental,www.arcoresiduos.com.br,"ARCO realiza gestão 360º de resíduos para estabelecimentos de P e M porte (bares, restaurantes, hotéis), O serviço, ...",https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1686329078523x117536423921054780/ARCO_Branding_ArquivosDaMar...,2,2026-03-24T19:40:13.364439-03:00
33,Amazonique,Ananindeua,PA,amazonique1@gmail.com,(91) 98843-4352,True,False,Site,Escala,Alimentos e Bebidas,,"Somos uma empresa 100% regional, produzindo sucos com frutas locais de fornecidas prioritariamente por cooperativas ...",https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1693433666756x292423239909519500/LETRA-A-EDIT%C3%81VEL.pdf.png\,3,2026-03-24T19:40:14.388459-03:00
43,Associação AMURMAM,Alvarães,AM,amurmam.rdsm@gmail.com,(97) 98402-6794,True,False,Site,Escala,Alimentos e Bebidas,,"É uma empacotadora de farinha que compra direto dos produtores da reserva e ajuda a não desmatar áreas primária, e u...",https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1690038251036x377800782205909950/SAVE_20230428_191207.jpg\,4,2026-03-24T19:40:15.922556-03:00
60,Avalia Soluções,Altamira,PA,avaliasolucoes@gmail.com,(93) 99169-6968,True,False,Site,Escala,Governo e Poder Público,,"A Avalia Soluções é uma empresa especializada na elaboração de Projetos Técnicos, com foco no desenvolvimento de fer...",https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1715914868928x411291133222913860/LOGO%20AVALIA%20%5BDOURADO%...,5,2026-03-24T19:40:17.035751-03:00
126,Drop Agricultura Ltda,Piracicaba,SP,,(19) 99971-5071,True,False,Email,Escala,Agronegócio,https://www.dropagricultura.com.br/,A Drop surgiu em 2016 com objetivo de desenvolver soluções para a tecnologia de aplicação de insumos agrícolas. Sedi...,https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1713354148520x512566601910962240/LOGO.jpg\,12,2026-03-24T19:40:24.594861-03:00
172,Foz Sustentável,Recife,PE,guilherme@fozsustentavel.com.br,(81) 97332-4880,True,False,Site,Escala,Impacto socioambiental,,A Foz Sustentável trabalha com soluções ultra eficientes para gestão hídrica e opera com foco em resolver o problema...,https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1695244526645x981115378552349700/default-image_550.png?_gl=1...,15,2026-03-24T19:40:27.602107-03:00
194,Inglês para Desesperados,Patos de Minas,MG,geraldotinoco@inglespdesesperados.com,(34) 99266-2222,True,False,Descrição,Escala,Educação,www.inglespdesesperados.com,,https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1692729074863x808223559631298100/9435_Ingles_para_Desesperad...,19,2026-03-24T19:40:29.610827-03:00
197,Inocular/Manejo biológico para uma agricultura mais sutentável.,Santa Maria,RS,inocular.contato@gmail.com,(55) 99615-4003,True,False,Site,Escala,Agronegócio,,Somos uma empresa incubada junto à Universidade Federal de Santa Maria. Nossa missão é levar alternativas de manejo ...,https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1711993261301x874545492555219800/Logo%20Inocular%20nova.png\,19,2026-03-24T19:40:29.611605-03:00
214,Homeplace Market,Fortaleza,CE,marketing@homeplacemarket.com.br,(85) 98780-3468,True,False,Site,Escala,Varejo e Atacado,,"Homeplace é uma rede de minimercados autônomos e inteligentes, com operação própria, que leva praticidade e tecnolog...",https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1757022143311x984694166994096100/Homeplace%20Logo.pdf\,17,2026-03-24T19:40:29.901274-03:00
279,Mais Solidário Educação e ESG,Salvador,BA,maissolidarioadm@gmail.com,(71) 99204-4379,True,False,Descrição,Escala,Educação,Bolsas MKT https://www.maissolidario.com.br Cursos: https://www.uniedutec.com.br,,https://b0a11c671efbdaffe869cdeeaa7add49.cdn.bubble.io/f1740409717451x738538966887891000/Prancheta%2019%20c%C3%B3pia...,